# PMUT Frequency Response Prediction
## Physics-Informed Machine Learning with FWHM

Cross-device prediction of PMUT frequency response curves using three complementary approaches.
Given amplitude-vs-frequency data from training PMUTs, predict the response of an unseen target PMUT.

---

### Dataset
| Property | Value |
|----------|-------|
| Total PMUTs | 16 (Batch A: PMUTs 1-8, Batch B: PMUTs 9-16) |
| Frequency points per PMUT | ~1000 |
| Target | `Amplitude_R_mean` (normalized via `StandardScaler`) |

### Three Experimental Regimes
| Regime | PMUTs | Type |
|--------|-------|------|
| Regime 1 | 1 to 3 | Short-range interpolation |
| Regime 2 | 3 to 8 | Medium-range interpolation |
| Regime 3 | 9 to 16 | Long-range cross-batch extrapolation |

### Approaches
| Section | Approach | Features | Prediction |
|---------|----------|----------|------------|
| 1 | **Pointwise** | `[N_PMUT, Freq_MHz]` per point | Full curve |
| 2 | **Multi-Output** | `[N_PMUT]` per device | Full 1000-pt vector at once |
| 3 | **FWHM-Window** | `[N_PMUT, Freq_MHz]` (peak band only) | In-band points only |

**Models:** Random Forest (RF) and Gradient Boosting (GB) for all approaches.


In [1]:
import subprocess, sys
pkgs = ['openpyxl', 'plotly', 'scikit-learn', 'pandas', 'numpy', 'nbformat', 'ipython']
for pkg in pkgs:
    subprocess.check_call(['uv', 'pip', 'install', '-q', pkg])
print('All dependencies installed.')


All dependencies installed.


In [2]:
import pandas as pd
import numpy as np
from sklearn.preprocessing import StandardScaler
import plotly.graph_objects as go

df1 = pd.read_excel('All Freq Response Data (1-8 PMUTs).xlsx', sheet_name='Averaged_Transfer')
df2 = pd.read_excel('All_Freq_Response_Data_PMUT9-16.xlsx', sheet_name='Averaged_Transfer')

def clean_frequency(val):
    if isinstance(val, str):
        val = val.replace(' x 10^', 'e').replace('x10^', 'e').replace(' ', '')
    return float(val)

df1['Frequency_MHz'] = df1['Frequency_Hz_rounded'].apply(clean_frequency) / 1e6
df2['Frequency_MHz'] = df2['Frequency_Hz'].apply(clean_frequency) / 1e6

cols = ['N_PMUT', 'Frequency_MHz', 'Amplitude_R_mean']
df_all = pd.concat([df1[cols].dropna(), df2[cols].dropna()], ignore_index=True)
df_all = df_all.sort_values(['N_PMUT', 'Frequency_MHz']).reset_index(drop=True)

amp_scaler = StandardScaler()
df_all['Amplitude_Scaled'] = amp_scaler.fit_transform(df_all[['Amplitude_R_mean']])

unique_pmuts = sorted(df_all['N_PMUT'].unique())

# Per-PMUT amplitude arrays aligned on PMUT-1 frequency grid
freqs_ref = df_all[df_all['N_PMUT'] == unique_pmuts[0]]['Frequency_MHz'].values
y_mo_list = [df_all[df_all['N_PMUT'] == p]['Amplitude_Scaled'].values for p in unique_pmuts]
y_mo  = np.array(y_mo_list)                        # (n_pmuts, n_freqs)
X_mo  = np.array(unique_pmuts).reshape(-1, 1)      # (n_pmuts, 1)

# Regime definitions (used by all sections)
regimes = {
    'Regime 1 (PMUTs 1-3)': {
        'train': [[1], [1,2]],
        'pred':  [[2], [3]]
    },
    'Regime 2 (PMUTs 3-8)': {
        'train': [[3,4], [3,4,5], [3,4,5,6], [3,4,5,6,7]],
        'pred':  [[5],   [6],     [7],        [8]]
    },
    'Regime 3 (PMUTs 9-16)': {
        'train': [[9,10], [9,10,11], [9,10,11,12], [9,10,11,12,13],
                  [9,10,11,12,13,14], [9,10,11,12,13,14,15]],
        'pred':  [[11], [12], [13], [14], [15], [16]]
    },
}

results = []   # Global MAE collector for Section 4 summary
colors = ['#1f77b4','#ff7f0e','#2ca02c','#9467bd','#8c564b','#e377c2']

print(f'Loaded {len(unique_pmuts)} PMUTs, {df_all.shape[0]} rows total')
print(f'Freq points per PMUT: {df_all.groupby("N_PMUT").size().unique()}')


Loaded 16 PMUTs, 16000 rows total
Freq points per PMUT: [1000]


---
## Section 1: Baseline — Pointwise Prediction

The simplest approach: train on **all individual (frequency, amplitude) points** from the
training PMUTs. The model sees `[N_PMUT, Frequency_MHz]` as input and learns to map device
identity + frequency to amplitude. At prediction time, it generates one amplitude value per
frequency point of the target PMUT, reconstructing the full curve.

| | |
|-|-|
| **Input features** | `[N_PMUT, Frequency_MHz]` — one row per frequency point |
| **Training samples** | `n_train_pmuts × n_freqs` individual points |
| **Prediction** | One value per frequency → full curve |
| **Models** | Random Forest, Gradient Boosting |


In [3]:
from sklearn.ensemble import RandomForestRegressor
from sklearn.metrics import mean_absolute_error, r2_score

print('--- RF: Pointwise ---')
rf_pw = RandomForestRegressor(n_estimators=100, random_state=42)

for r_name, r_data in regimes.items():
    for t_pmuts, p_pmut in zip(r_data['train'], r_data['pred']):
        target = p_pmut[0]
        step_label = f'Train{t_pmuts}>{target}'

        mask_train  = df_all['N_PMUT'].isin(t_pmuts)
        mask_target = df_all['N_PMUT'] == target
        rf_pw.fit(df_all.loc[mask_train,  ['N_PMUT','Frequency_MHz']],
                  df_all.loc[mask_train,  'Amplitude_Scaled'])

        target_freqs = df_all.loc[mask_target, 'Frequency_MHz'].values
        preds  = amp_scaler.inverse_transform(
            rf_pw.predict(df_all.loc[mask_target, ['N_PMUT','Frequency_MHz']]).reshape(-1,1)).flatten()
        actual = amp_scaler.inverse_transform(
            df_all.loc[mask_target, 'Amplitude_Scaled'].values.reshape(-1,1)).flatten()

        mae = mean_absolute_error(actual, preds)
        r2  = r2_score(actual, preds)
        results.append({'Model':'RF','Approach':'Pointwise','Regime':r_name,
                        'Step':step_label,'Target':target,'MAE':mae,'R2':r2})

        fig = go.Figure()
        for i, p in enumerate(t_pmuts):
            tr_f = df_all[df_all['N_PMUT']==p]['Frequency_MHz'].values
            tr_a = amp_scaler.inverse_transform(
                df_all[df_all['N_PMUT']==p]['Amplitude_Scaled'].values.reshape(-1,1)).flatten()
            fig.add_trace(go.Scatter(x=tr_f, y=tr_a, mode='lines',
                line=dict(dash='dot', width=2, color=colors[i%len(colors)]),
                opacity=0.6, name=f'Train PMUT {p}'))
        fig.add_trace(go.Scatter(x=target_freqs, y=actual, mode='lines',
            line=dict(color='black', width=3), name=f'Actual PMUT {target}'))
        fig.add_trace(go.Scatter(x=target_freqs, y=preds, mode='lines',
            line=dict(color='#d62728', dash='dash', width=2.5), name='RF Pointwise'))
        fig.update_layout(
            title=f'RF Pointwise | {r_name}: Train {t_pmuts} -> Predict PMUT {target}',
            xaxis_title='Frequency (MHz)', yaxis_title='Amplitude_R_mean',
            template='plotly_white',
            legend=dict(yanchor='top', y=1, xanchor='left', x=1.02,
                bgcolor='rgba(255,255,255,0.8)', bordercolor='gray', borderwidth=1),
            margin=dict(r=260))
        fig.add_annotation(xref='paper', yref='paper', x=1.02, y=0.0,
            yanchor='bottom', xanchor='left', showarrow=False, align='left',
            text=f'<b>RF Pointwise</b><br>MAE: {mae:.6f}<br>R2: {r2:.4f}',
            bgcolor='white', bordercolor='black', borderwidth=1, borderpad=10)
        fig.show()


--- RF: Pointwise ---


In [4]:
from sklearn.ensemble import GradientBoostingRegressor

print('--- GB: Pointwise ---')
gb_pw = GradientBoostingRegressor(n_estimators=100, random_state=42)

for r_name, r_data in regimes.items():
    for t_pmuts, p_pmut in zip(r_data['train'], r_data['pred']):
        target = p_pmut[0]
        step_label = f'Train{t_pmuts}>{target}'

        mask_train  = df_all['N_PMUT'].isin(t_pmuts)
        mask_target = df_all['N_PMUT'] == target
        gb_pw.fit(df_all.loc[mask_train,  ['N_PMUT','Frequency_MHz']],
                  df_all.loc[mask_train,  'Amplitude_Scaled'])

        target_freqs = df_all.loc[mask_target, 'Frequency_MHz'].values
        preds  = amp_scaler.inverse_transform(
            gb_pw.predict(df_all.loc[mask_target, ['N_PMUT','Frequency_MHz']]).reshape(-1,1)).flatten()
        actual = amp_scaler.inverse_transform(
            df_all.loc[mask_target, 'Amplitude_Scaled'].values.reshape(-1,1)).flatten()

        mae = mean_absolute_error(actual, preds)
        r2  = r2_score(actual, preds)
        results.append({'Model':'GB','Approach':'Pointwise','Regime':r_name,
                        'Step':step_label,'Target':target,'MAE':mae,'R2':r2})

        fig = go.Figure()
        for i, p in enumerate(t_pmuts):
            tr_f = df_all[df_all['N_PMUT']==p]['Frequency_MHz'].values
            tr_a = amp_scaler.inverse_transform(
                df_all[df_all['N_PMUT']==p]['Amplitude_Scaled'].values.reshape(-1,1)).flatten()
            fig.add_trace(go.Scatter(x=tr_f, y=tr_a, mode='lines',
                line=dict(dash='dot', width=2, color=colors[i%len(colors)]),
                opacity=0.6, name=f'Train PMUT {p}'))
        fig.add_trace(go.Scatter(x=target_freqs, y=actual, mode='lines',
            line=dict(color='black', width=3), name=f'Actual PMUT {target}'))
        fig.add_trace(go.Scatter(x=target_freqs, y=preds, mode='lines',
            line=dict(color='#2ca02c', dash='dash', width=2.5), name='GB Pointwise'))
        fig.update_layout(
            title=f'GB Pointwise | {r_name}: Train {t_pmuts} -> Predict PMUT {target}',
            xaxis_title='Frequency (MHz)', yaxis_title='Amplitude_R_mean',
            template='plotly_white',
            legend=dict(yanchor='top', y=1, xanchor='left', x=1.02,
                bgcolor='rgba(255,255,255,0.8)', bordercolor='gray', borderwidth=1),
            margin=dict(r=260))
        fig.add_annotation(xref='paper', yref='paper', x=1.02, y=0.0,
            yanchor='bottom', xanchor='left', showarrow=False, align='left',
            text=f'<b>GB Pointwise</b><br>MAE: {mae:.6f}<br>R2: {r2:.4f}',
            bgcolor='white', bordercolor='black', borderwidth=1, borderpad=10)
        fig.show()


--- GB: Pointwise ---


---
## Section 2: Multi-Output Prediction

Instead of predicting one frequency point at a time, the **multi-output approach** treats
the entire 1000-point amplitude curve as a single prediction target. The model learns a
mapping from device identity to full curve shape in one shot.

| | |
|-|-|
| **Input features** | `[N_PMUT]` — one row per device |
| **Training samples** | `n_train_pmuts` rows (one per PMUT) |
| **Output** | Full amplitude vector of length `n_freqs` |
| **Models** | RF (native multi-output), GB (via `MultiOutputRegressor`) |

This tests whether the model can interpolate/extrapolate between **whole device profiles**
rather than individual frequency points. With very few training samples (1-6 PMUTs),
this is a highly challenging regression task.


In [5]:
from sklearn.ensemble import RandomForestRegressor

print('--- RF: Multi-Output ---')
rf_mo = RandomForestRegressor(n_estimators=100, random_state=42)

for r_name, r_data in regimes.items():
    for t_pmuts, p_pmut in zip(r_data['train'], r_data['pred']):
        target = p_pmut[0]
        step_label = f'Train{t_pmuts}>{target}'

        idx_train  = [unique_pmuts.index(p) for p in t_pmuts]
        idx_target = unique_pmuts.index(target)

        rf_mo.fit(X_mo[idx_train], y_mo[idx_train])   # (n_train, 1) -> (n_train, n_freqs)

        preds_scaled = rf_mo.predict(X_mo[[idx_target]])[0]   # (1, n_freqs) -> (n_freqs,)
        preds  = amp_scaler.inverse_transform(preds_scaled.reshape(-1,1)).flatten()
        actual = amp_scaler.inverse_transform(y_mo[idx_target].reshape(-1,1)).flatten()
        target_freqs = df_all[df_all['N_PMUT'] == target]['Frequency_MHz'].values

        mae = mean_absolute_error(actual, preds)
        r2  = r2_score(actual, preds)
        results.append({'Model':'RF','Approach':'Multi-Output','Regime':r_name,
                        'Step':step_label,'Target':target,'MAE':mae,'R2':r2})

        fig = go.Figure()
        for i, p in enumerate(t_pmuts):
            tr_f = df_all[df_all['N_PMUT']==p]['Frequency_MHz'].values
            tr_a = amp_scaler.inverse_transform(y_mo[unique_pmuts.index(p)].reshape(-1,1)).flatten()
            fig.add_trace(go.Scatter(x=tr_f, y=tr_a, mode='lines',
                line=dict(dash='dot', width=2, color=colors[i%len(colors)]),
                opacity=0.6, name=f'Train PMUT {p}'))
        fig.add_trace(go.Scatter(x=target_freqs, y=actual, mode='lines',
            line=dict(color='black', width=3), name=f'Actual PMUT {target}'))
        fig.add_trace(go.Scatter(x=target_freqs, y=preds, mode='lines',
            line=dict(color='#d62728', dash='dash', width=2.5), name='RF Multi-Output'))
        fig.update_layout(
            title=f'RF Multi-Output | {r_name}: Train {t_pmuts} -> Predict PMUT {target}',
            xaxis_title='Frequency (MHz)', yaxis_title='Amplitude_R_mean',
            template='plotly_white',
            legend=dict(yanchor='top', y=1, xanchor='left', x=1.02,
                bgcolor='rgba(255,255,255,0.8)', bordercolor='gray', borderwidth=1),
            margin=dict(r=260))
        fig.add_annotation(xref='paper', yref='paper', x=1.02, y=0.0,
            yanchor='bottom', xanchor='left', showarrow=False, align='left',
            text=f'<b>RF Multi-Output</b><br>MAE: {mae:.6f}<br>R2: {r2:.4f}',
            bgcolor='white', bordercolor='black', borderwidth=1, borderpad=10)
        fig.show()


--- RF: Multi-Output ---


In [6]:
from sklearn.ensemble import GradientBoostingRegressor
from sklearn.multioutput import MultiOutputRegressor

print('--- GB: Multi-Output ---')
gb_mo = MultiOutputRegressor(GradientBoostingRegressor(n_estimators=100, random_state=42),
                             n_jobs=-1)

for r_name, r_data in regimes.items():
    for t_pmuts, p_pmut in zip(r_data['train'], r_data['pred']):
        target = p_pmut[0]
        step_label = f'Train{t_pmuts}>{target}'

        idx_train  = [unique_pmuts.index(p) for p in t_pmuts]
        idx_target = unique_pmuts.index(target)

        gb_mo.fit(X_mo[idx_train], y_mo[idx_train])

        preds_scaled = gb_mo.predict(X_mo[[idx_target]])[0]
        preds  = amp_scaler.inverse_transform(preds_scaled.reshape(-1,1)).flatten()
        actual = amp_scaler.inverse_transform(y_mo[idx_target].reshape(-1,1)).flatten()
        target_freqs = df_all[df_all['N_PMUT'] == target]['Frequency_MHz'].values

        mae = mean_absolute_error(actual, preds)
        r2  = r2_score(actual, preds)
        results.append({'Model':'GB','Approach':'Multi-Output','Regime':r_name,
                        'Step':step_label,'Target':target,'MAE':mae,'R2':r2})

        fig = go.Figure()
        for i, p in enumerate(t_pmuts):
            tr_f = df_all[df_all['N_PMUT']==p]['Frequency_MHz'].values
            tr_a = amp_scaler.inverse_transform(y_mo[unique_pmuts.index(p)].reshape(-1,1)).flatten()
            fig.add_trace(go.Scatter(x=tr_f, y=tr_a, mode='lines',
                line=dict(dash='dot', width=2, color=colors[i%len(colors)]),
                opacity=0.6, name=f'Train PMUT {p}'))
        fig.add_trace(go.Scatter(x=target_freqs, y=actual, mode='lines',
            line=dict(color='black', width=3), name=f'Actual PMUT {target}'))
        fig.add_trace(go.Scatter(x=target_freqs, y=preds, mode='lines',
            line=dict(color='#2ca02c', dash='dash', width=2.5), name='GB Multi-Output'))
        fig.update_layout(
            title=f'GB Multi-Output | {r_name}: Train {t_pmuts} -> Predict PMUT {target}',
            xaxis_title='Frequency (MHz)', yaxis_title='Amplitude_R_mean',
            template='plotly_white',
            legend=dict(yanchor='top', y=1, xanchor='left', x=1.02,
                bgcolor='rgba(255,255,255,0.8)', bordercolor='gray', borderwidth=1),
            margin=dict(r=260))
        fig.add_annotation(xref='paper', yref='paper', x=1.02, y=0.0,
            yanchor='bottom', xanchor='left', showarrow=False, align='left',
            text=f'<b>GB Multi-Output</b><br>MAE: {mae:.6f}<br>R2: {r2:.4f}',
            bgcolor='white', bordercolor='black', borderwidth=1, borderpad=10)
        fig.show()


--- GB: Multi-Output ---


---
## Section 3: FWHM — Background

**Full Width at Half Maximum (FWHM)** is the width of the resonance peak measured at 50% of
its peak height **above the baseline**:

```
baseline  = A_min   (lowest amplitude in the sweep)
h_half    = A_min + (A_max - A_min) / 2
x1 (f_lo) = lowest  frequency where A(f) >= h_half
x2 (f_hi) = highest frequency where A(f) >= h_half
FWHM      = x2 - x1
Q-factor  = f_peak / FWHM
```

Using baseline-corrected half-max ensures x1 and x2 correctly identify the peak band edges
even when the amplitude curve has a non-zero floor.

| FWHM | Q-factor | Meaning |
|------|----------|---------|
| Small | High | Sharp resonance — selective, high sensitivity at peak |
| Large | Low | Broad resonance — more bandwidth, lower peak sensitivity |


In [7]:
# Compute baseline-corrected FWHM per PMUT
fwhm_data = []
for p in unique_pmuts:
    sub    = df_all[df_all['N_PMUT'] == p]
    a_min  = sub['Amplitude_R_mean'].min()
    a_max  = sub['Amplitude_R_mean'].max()
    h_half = a_min + (a_max - a_min) / 2
    above  = sub[sub['Amplitude_R_mean'] >= h_half]
    f_peak = sub.loc[sub['Amplitude_R_mean'].idxmax(), 'Frequency_MHz']
    f_lo   = above['Frequency_MHz'].min()
    f_hi   = above['Frequency_MHz'].max()
    fwhm   = f_hi - f_lo
    q      = round(f_peak / fwhm, 2) if fwhm > 0 else float('nan')
    fwhm_data.append({'N_PMUT': p, 'f_peak_MHz': round(f_peak,4),
                       'f_lo_MHz': round(f_lo,4), 'f_hi_MHz': round(f_hi,4),
                       'FWHM_MHz': round(fwhm,4), 'Q_factor': q})

df_fwhm = pd.DataFrame(fwhm_data)
print(df_fwhm.to_string(index=False))

fig = go.Figure()
fig.add_trace(go.Bar(x=df_fwhm['N_PMUT'], y=df_fwhm['FWHM_MHz'],
    marker_color='steelblue',
    text=[f'{v:.3f}' for v in df_fwhm['FWHM_MHz']], textposition='outside',
    name='FWHM (MHz)'))
fig.update_layout(title='FWHM per PMUT (baseline-corrected)',
    xaxis_title='PMUT', yaxis_title='FWHM (MHz)', template='plotly_white',
    xaxis=dict(tickmode='linear', tick0=1, dtick=1))
fig.show()

fig2 = go.Figure()
fig2.add_trace(go.Scatter(x=df_fwhm['N_PMUT'], y=df_fwhm['Q_factor'],
    mode='markers+lines', marker=dict(size=10, color='darkorange'),
    line=dict(color='darkorange'), name='Q-factor'))
fig2.update_layout(title='Q-Factor per PMUT (f_peak / FWHM)',
    xaxis_title='PMUT', yaxis_title='Q-factor', template='plotly_white',
    xaxis=dict(tickmode='linear', tick0=1, dtick=1))
fig2.show()


 N_PMUT  f_peak_MHz  f_lo_MHz  f_hi_MHz  FWHM_MHz  Q_factor
      1      0.9916    0.8522    2.2478    1.3956      0.71
      2      0.9916    0.1444    0.9980    0.8536      1.16
      3      0.4741    0.4263    0.5155    0.0893      5.31
      4      0.4726    0.4277    0.5155    0.0879      5.38
      5      0.4726    0.4263    0.5139    0.0876      5.40
      6      0.4711    0.4263    0.5139    0.0876      5.38
      7      0.4726    0.4263    0.5139    0.0876      5.40
      8      0.4726    0.4263    0.5139    0.0876      5.40
      9      0.4680    0.4222    0.5106    0.0884      5.29
     10      0.4680    0.4222    0.5106    0.0884      5.29
     11      0.4696    0.4235    0.5122    0.0887      5.29
     12      0.4665    0.4195    0.5057    0.0862      5.41
     13      0.4680    0.4208    0.5057    0.0848      5.52
     14      0.4680    0.4208    0.5057    0.0848      5.52
     15      0.4696    0.4222    0.5073    0.0851      5.52
     16      0.4696    0.4235    0.5089 

---
## Section 4: FWHM-Window Training

**Training:** filter each training PMUT's data to only its FWHM band `[x1, x2]`.
The model sees only the resonance peak region — not the flat baseline.

**Prediction:** predict only at the target PMUT's own `[x1, x2]` frequency points.
Since the model was trained exclusively on resonance-band data, asking it to predict
outside that range would be meaningless extrapolation. MAE is therefore evaluated
only within the target's FWHM band.

| | Standard Pointwise | FWHM-Window |
|-|--------------------|-------------|
| Training data | All ~1000 pts (baseline + peak) | ~50-150 pts (peak band only) |
| Prediction range | Full sweep | Within target FWHM band only |
| MAE computed on | Full curve | In-band points only |

The shaded region on each plot shows the target PMUT's FWHM window.
**Models:** RF, GB


In [8]:
def get_fwhm_window(pmut):
    """Baseline-corrected FWHM band: returns (f_lo, f_hi) for a PMUT."""
    sub    = df_all[df_all['N_PMUT'] == pmut]
    a_min  = sub['Amplitude_R_mean'].min()
    a_max  = sub['Amplitude_R_mean'].max()
    h_half = a_min + (a_max - a_min) / 2
    above  = sub[sub['Amplitude_R_mean'] >= h_half]
    return above['Frequency_MHz'].min(), above['Frequency_MHz'].max()

def get_window_train_df(t_pmuts):
    """FWHM-band rows from each training PMUT's own curve."""
    parts = []
    for p in t_pmuts:
        f_lo, f_hi = get_fwhm_window(p)
        mask = ((df_all['N_PMUT'] == p) &
                (df_all['Frequency_MHz'] >= f_lo) &
                (df_all['Frequency_MHz'] <= f_hi))
        parts.append(df_all[mask])
    return pd.concat(parts, ignore_index=True)

# Sanity check: in-band pts should now be << total pts
print(f'{'PMUT':>4}  {'f_lo (MHz)':>12}  {'f_peak (MHz)':>14}  {'f_hi (MHz)':>12}  {'in-band pts':>12}  {'total pts':>10}')
print('-' * 72)
for p in unique_pmuts:
    f_lo, f_hi = get_fwhm_window(p)
    sub    = df_all[df_all['N_PMUT'] == p]
    f_peak = sub.loc[sub['Amplitude_R_mean'].idxmax(), 'Frequency_MHz']
    n_in   = len(sub[(sub['Frequency_MHz'] >= f_lo) & (sub['Frequency_MHz'] <= f_hi)])
    n_tot  = len(sub)
    print(f'{p:>4}  {f_lo:>12.4f}  {f_peak:>14.4f}  {f_hi:>12.4f}  {n_in:>12}  {n_tot:>10}')


PMUT    f_lo (MHz)    f_peak (MHz)    f_hi (MHz)   in-band pts   total pts
------------------------------------------------------------------------
   1        0.8522          0.9916        2.2478           302        1000
   2        0.1444          0.9916        0.9980           601        1000
   3        0.4263          0.4741        0.5155            60        1000
   4        0.4277          0.4726        0.5155            59        1000
   5        0.4263          0.4726        0.5139            59        1000
   6        0.4263          0.4711        0.5139            59        1000
   7        0.4263          0.4726        0.5139            59        1000
   8        0.4263          0.4726        0.5139            59        1000
   9        0.4222          0.4680        0.5106            60        1000
  10        0.4222          0.4680        0.5106            60        1000
  11        0.4235          0.4696        0.5122            60        1000
  12        0.4195         

In [9]:
from sklearn.ensemble import RandomForestRegressor

print('--- RF: FWHM-Window (train + predict within band) ---')
rf_win = RandomForestRegressor(n_estimators=100, random_state=42)

for r_name, r_data in regimes.items():
    for t_pmuts, p_pmut in zip(r_data['train'], r_data['pred']):
        target = p_pmut[0]
        step_label = f'Train{t_pmuts}>{target}'

        # Train on in-band points of training PMUTs
        df_window = get_window_train_df(t_pmuts)
        rf_win.fit(df_window[['N_PMUT','Frequency_MHz']], df_window['Amplitude_Scaled'])

        # Predict only within the target's own FWHM band
        t_lo, t_hi = get_fwhm_window(target)
        sub_target = df_all[(df_all['N_PMUT'] == target) &
                             (df_all['Frequency_MHz'] >= t_lo) &
                             (df_all['Frequency_MHz'] <= t_hi)]
        target_band_freqs = sub_target['Frequency_MHz'].values

        preds  = amp_scaler.inverse_transform(
            rf_win.predict(sub_target[['N_PMUT','Frequency_MHz']]).reshape(-1,1)).flatten()
        actual_band = amp_scaler.inverse_transform(
            sub_target['Amplitude_Scaled'].values.reshape(-1,1)).flatten()

        # Full actual curve for context
        mask_all = df_all['N_PMUT'] == target
        full_freqs  = df_all.loc[mask_all, 'Frequency_MHz'].values
        full_actual = amp_scaler.inverse_transform(
            df_all.loc[mask_all, 'Amplitude_Scaled'].values.reshape(-1,1)).flatten()

        mae = mean_absolute_error(actual_band, preds)
        r2  = r2_score(actual_band, preds)
        results.append({'Model':'RF','Approach':'FWHM Window','Regime':r_name,
                        'Step':step_label,'Target':target,'MAE':mae,'R2':r2})

        fig = go.Figure()
        # Training curves
        for i, p in enumerate(t_pmuts):
            tr_f = df_all[df_all['N_PMUT']==p]['Frequency_MHz'].values
            tr_a = amp_scaler.inverse_transform(
                df_all[df_all['N_PMUT']==p]['Amplitude_Scaled'].values.reshape(-1,1)).flatten()
            p_lo, p_hi = get_fwhm_window(p)
            fig.add_trace(go.Scatter(x=tr_f, y=tr_a, mode='lines',
                line=dict(dash='dot', width=2, color=colors[i%len(colors)]),
                opacity=0.5, name=f'Train PMUT {p}'))
            fig.add_vrect(x0=p_lo, x1=p_hi, fillcolor=colors[i%len(colors)],
                opacity=0.07, layer='below', line_width=0,
                annotation_text=f'FWHM {p}', annotation_position='top left')
        # Full actual curve (context)
        fig.add_trace(go.Scatter(x=full_freqs, y=full_actual, mode='lines',
            line=dict(color='black', width=2, dash='dot'), opacity=0.4,
            name=f'Actual PMUT {target} (full)'))
        # Shaded target FWHM window
        fig.add_vrect(x0=t_lo, x1=t_hi, fillcolor='black',
            opacity=0.06, layer='below', line_width=1,
            annotation_text='Target FWHM', annotation_position='top right')
        # In-band actual and prediction
        fig.add_trace(go.Scatter(x=target_band_freqs, y=actual_band, mode='lines',
            line=dict(color='black', width=3), name=f'Actual PMUT {target} (in-band)'))
        fig.add_trace(go.Scatter(x=target_band_freqs, y=preds, mode='lines',
            line=dict(color='#d62728', dash='dash', width=2.5), name='RF FWHM-Window'))
        fig.update_layout(
            title=f'RF FWHM-Window | {r_name}: Train {t_pmuts} -> Predict PMUT {target} (in-band)',
            xaxis_title='Frequency (MHz)', yaxis_title='Amplitude_R_mean',
            template='plotly_white',
            legend=dict(yanchor='top', y=1, xanchor='left', x=1.02,
                bgcolor='rgba(255,255,255,0.8)', bordercolor='gray', borderwidth=1),
            margin=dict(r=270))
        fig.add_annotation(xref='paper', yref='paper', x=1.02, y=0.0,
            yanchor='bottom', xanchor='left', showarrow=False, align='left',
            text=f'<b>RF FWHM-Window</b><br>MAE (in-band): {mae:.6f}<br>R2: {r2:.4f}<br>Band: [{t_lo:.3f}, {t_hi:.3f}] MHz',
            bgcolor='white', bordercolor='black', borderwidth=1, borderpad=10)
        fig.show()


--- RF: FWHM-Window (train + predict within band) ---


In [10]:
from sklearn.ensemble import GradientBoostingRegressor

print('--- GB: FWHM-Window (train + predict within band) ---')
gb_win = GradientBoostingRegressor(n_estimators=100, random_state=42)

for r_name, r_data in regimes.items():
    for t_pmuts, p_pmut in zip(r_data['train'], r_data['pred']):
        target = p_pmut[0]
        step_label = f'Train{t_pmuts}>{target}'

        df_window = get_window_train_df(t_pmuts)
        gb_win.fit(df_window[['N_PMUT','Frequency_MHz']], df_window['Amplitude_Scaled'])

        t_lo, t_hi = get_fwhm_window(target)
        sub_target = df_all[(df_all['N_PMUT'] == target) &
                             (df_all['Frequency_MHz'] >= t_lo) &
                             (df_all['Frequency_MHz'] <= t_hi)]
        target_band_freqs = sub_target['Frequency_MHz'].values

        preds  = amp_scaler.inverse_transform(
            gb_win.predict(sub_target[['N_PMUT','Frequency_MHz']]).reshape(-1,1)).flatten()
        actual_band = amp_scaler.inverse_transform(
            sub_target['Amplitude_Scaled'].values.reshape(-1,1)).flatten()

        mask_all = df_all['N_PMUT'] == target
        full_freqs  = df_all.loc[mask_all, 'Frequency_MHz'].values
        full_actual = amp_scaler.inverse_transform(
            df_all.loc[mask_all, 'Amplitude_Scaled'].values.reshape(-1,1)).flatten()

        mae = mean_absolute_error(actual_band, preds)
        r2  = r2_score(actual_band, preds)
        results.append({'Model':'GB','Approach':'FWHM Window','Regime':r_name,
                        'Step':step_label,'Target':target,'MAE':mae,'R2':r2})

        fig = go.Figure()
        for i, p in enumerate(t_pmuts):
            tr_f = df_all[df_all['N_PMUT']==p]['Frequency_MHz'].values
            tr_a = amp_scaler.inverse_transform(
                df_all[df_all['N_PMUT']==p]['Amplitude_Scaled'].values.reshape(-1,1)).flatten()
            p_lo, p_hi = get_fwhm_window(p)
            fig.add_trace(go.Scatter(x=tr_f, y=tr_a, mode='lines',
                line=dict(dash='dot', width=2, color=colors[i%len(colors)]),
                opacity=0.5, name=f'Train PMUT {p}'))
            fig.add_vrect(x0=p_lo, x1=p_hi, fillcolor=colors[i%len(colors)],
                opacity=0.07, layer='below', line_width=0,
                annotation_text=f'FWHM {p}', annotation_position='top left')
        fig.add_trace(go.Scatter(x=full_freqs, y=full_actual, mode='lines',
            line=dict(color='black', width=2, dash='dot'), opacity=0.4,
            name=f'Actual PMUT {target} (full)'))
        fig.add_vrect(x0=t_lo, x1=t_hi, fillcolor='black',
            opacity=0.06, layer='below', line_width=1,
            annotation_text='Target FWHM', annotation_position='top right')
        fig.add_trace(go.Scatter(x=target_band_freqs, y=actual_band, mode='lines',
            line=dict(color='black', width=3), name=f'Actual PMUT {target} (in-band)'))
        fig.add_trace(go.Scatter(x=target_band_freqs, y=preds, mode='lines',
            line=dict(color='#2ca02c', dash='dash', width=2.5), name='GB FWHM-Window'))
        fig.update_layout(
            title=f'GB FWHM-Window | {r_name}: Train {t_pmuts} -> Predict PMUT {target} (in-band)',
            xaxis_title='Frequency (MHz)', yaxis_title='Amplitude_R_mean',
            template='plotly_white',
            legend=dict(yanchor='top', y=1, xanchor='left', x=1.02,
                bgcolor='rgba(255,255,255,0.8)', bordercolor='gray', borderwidth=1),
            margin=dict(r=270))
        fig.add_annotation(xref='paper', yref='paper', x=1.02, y=0.0,
            yanchor='bottom', xanchor='left', showarrow=False, align='left',
            text=f'<b>GB FWHM-Window</b><br>MAE (in-band): {mae:.6f}<br>R2: {r2:.4f}<br>Band: [{t_lo:.3f}, {t_hi:.3f}] MHz',
            bgcolor='white', bordercolor='black', borderwidth=1, borderpad=10)
        fig.show()


--- GB: FWHM-Window (train + predict within band) ---


In [11]:
# ── Print all results in a structured readable format ──────────────────────
import pandas as pd

df_results = pd.DataFrame(results)

# Full results table
pd.set_option('display.max_rows', 200)
pd.set_option('display.max_colwidth', 40)
pd.set_option('display.float_format', '{:.6f}'.format)
print('=' * 90)
print('FULL RESULTS TABLE')
print('=' * 90)
print(df_results[['Model','Approach','Regime','Step','Target','MAE','R2']].to_string(index=False))

# Per-approach summary
print('\n' + '=' * 90)
print('MEAN MAE AND R2 BY MODEL x APPROACH')
print('=' * 90)
summary = df_results.groupby(['Approach','Model'])[['MAE','R2']].agg(
    Mean_MAE=('MAE','mean'), Std_MAE=('MAE','std'),
    Min_MAE=('MAE','min'),   Max_MAE=('MAE','max'),
    Mean_R2=('R2','mean'),   Min_R2=('R2','min')
).reset_index().sort_values('Mean_MAE')
print(summary.to_string(index=False))

# Per-regime summary
print('\n' + '=' * 90)
print('MEAN MAE BY REGIME x APPROACH x MODEL')
print('=' * 90)
regime_summary = df_results.groupby(['Regime','Approach','Model'])['MAE'].mean().reset_index()
regime_summary.columns = ['Regime','Approach','Model','Mean_MAE']
print(regime_summary.sort_values(['Regime','Mean_MAE']).to_string(index=False))

# Negative R2 cases
neg_r2 = df_results[df_results['R2'] < 0][['Model','Approach','Regime','Step','Target','MAE','R2']]
print('\n' + '=' * 90)
print(f'NEGATIVE R2 CASES: {len(neg_r2)} out of {len(df_results)} total predictions')
print('=' * 90)
if len(neg_r2) > 0:
    print(neg_r2.to_string(index=False))
else:
    print('None')


FULL RESULTS TABLE
Model     Approach                Regime                                Step  Target      MAE            R2
   RF    Pointwise  Regime 1 (PMUTs 1-3)                          Train[1]>2       2 0.462313 -11527.691671
   RF    Pointwise  Regime 1 (PMUTs 1-3)                       Train[1, 2]>3       3 0.096258   -322.124083
   RF    Pointwise  Regime 2 (PMUTs 3-8)                       Train[3, 4]>5       5 0.003013      0.674082
   RF    Pointwise  Regime 2 (PMUTs 3-8)                    Train[3, 4, 5]>6       6 0.001864      0.876319
   RF    Pointwise  Regime 2 (PMUTs 3-8)                 Train[3, 4, 5, 6]>7       7 0.001150      0.953289
   RF    Pointwise  Regime 2 (PMUTs 3-8)              Train[3, 4, 5, 6, 7]>8       8 0.000944      0.969062
   RF    Pointwise Regime 3 (PMUTs 9-16)                     Train[9, 10]>11      11 0.000403      0.993867
   RF    Pointwise Regime 3 (PMUTs 9-16)                 Train[9, 10, 11]>12      12 0.005636     -0.165976
   RF    

---
## Section 5: Model Comparison & Summary

Comparing MAE across all 6 model/approach combinations. Note that **FWHM-Window MAE**
is evaluated only on the in-band points of the target PMUT, while **Pointwise** and
**Multi-Output MAE** cover the full sweep — so they are not directly equivalent.

| Approach | Prediction scope | Training data |
|----------|-----------------|---------------|
| Pointwise | Full curve | All freq points |
| Multi-Output | Full curve | One row per PMUT |
| FWHM-Window | In-band only | FWHM-band points only |

> Run all sections above before running this cell.


In [12]:
df_results = pd.DataFrame(results)

approach_colors = {
    ('RF', 'Pointwise'):    '#1f77b4',
    ('GB', 'Pointwise'):    '#aec7e8',
    ('RF', 'Multi-Output'): '#d62728',
    ('GB', 'Multi-Output'): '#ff9896',
    ('RF', 'FWHM Window'):  '#2ca02c',
    ('GB', 'FWHM Window'):  '#98df8a',
}

# Per-regime grouped bar charts
for regime_name in df_results['Regime'].unique():
    df_r = df_results[df_results['Regime'] == regime_name]
    fig  = go.Figure()
    for (model, approach), color in approach_colors.items():
        df_sub = df_r[(df_r['Model']==model) & (df_r['Approach']==approach)]
        if df_sub.empty:
            continue
        fig.add_trace(go.Bar(
            x=df_sub['Step'], y=df_sub['MAE'],
            name=f'{model} / {approach}', marker_color=color,
            text=[f'{v:.5f}' for v in df_sub['MAE']], textposition='outside'))
    fig.update_layout(
        title=f'MAE Comparison -- {regime_name}',
        xaxis_title='Prediction Step', yaxis_title='MAE',
        barmode='group', template='plotly_white',
        legend=dict(yanchor='top', y=1, xanchor='left', x=1.02,
            bgcolor='rgba(255,255,255,0.8)', bordercolor='gray', borderwidth=1),
        margin=dict(r=280))
    fig.show()

# Overall mean MAE by Model x Approach
df_avg = (df_results.groupby(['Model','Approach'])[['MAE','R2']]
            .mean().reset_index().sort_values('MAE'))
df_avg['Label'] = df_avg['Model'] + ' / ' + df_avg['Approach']
fig_avg = go.Figure(go.Bar(
    x=df_avg['Label'], y=df_avg['MAE'],
    marker_color=[approach_colors.get((r['Model'], r['Approach']), 'gray')
                  for _, r in df_avg.iterrows()],
    text=[f'{v:.5f}' for v in df_avg['MAE']], textposition='outside'))
fig_avg.update_layout(
    title='Overall Mean MAE by Model and Approach (all regimes)',
    xaxis_title='Model / Approach', yaxis_title='Mean MAE',
    template='plotly_white', margin=dict(b=140))
fig_avg.show()

print('\n=== Mean MAE Summary ===')
print(df_avg[['Label','MAE','R2']].to_string(index=False))



=== Mean MAE Summary ===
            Label      MAE           R2
GB / Multi-Output 0.047651  -986.801019
   RF / Pointwise 0.047658  -986.793158
   GB / Pointwise 0.047694  -986.811241
 GB / FWHM Window 0.048198 -1629.130341
 RF / FWHM Window 0.048253 -1629.357226
RF / Multi-Output 0.058233 -1096.004365
